In [1]:
!which python; python --version

/Users/swagatam/Desktop/oellm/surrogate_based_scaling_laws/.venv/bin/python
Python 3.12.12


In [2]:
import warnings
warnings.filterwarnings("ignore")

import numpy as np
import pandas as pd
import matplotlib.pyplot as plt

from scipy.optimize import curve_fit
from pathlib import Path

import sys; sys.path.append("../")

from core import GRID_TARGET, MAX_ITERS
from core.forms import PARAMETRIC_FORMS
from core.selection import SELECTION
from core.surrogates import MODELS, build_surrogate
from core.surrogates.gp import KERNEL_NAMES, MEAN_FORM_NAMES
from core.fitting import build_fit, print_fit_results  # noqa: F401  (re-exported for pipelines)
from core.utils.data import next_batch_compute, resolve_grid_features, FEATURE_SETS, split_search_space, data_preprocess

from scaling.utils import fit_parametric_form, functional_form_L0, get_pareto_frontier

In [3]:
from core import DEFAULT_FEATURES, ARCH_FEATURES, DATA_FEATURES, GRID_TARGET

INPUT_X = DEFAULT_FEATURES
OUTPUT_Y = GRID_TARGET
loss_key = GRID_TARGET

MAX_ITERS = 1000  # depends on the train split size

print(f"Using {len(INPUT_X)} features: {INPUT_X}, target: {OUTPUT_Y}")
print(SELECTION.keys(), MODELS.keys())

Using 4 features: ['N', 'D', 'lr', 'gbsz'], target: loss
dict_keys(['random', 'local_search', 'max_variance', 'farthest_point', 'ei', 'ei_per_cost']) dict_keys(['none', 'gp', 'tabpfn', 'ag'])


## Load original data

In [4]:
def format_scientific(val):
    s = f"{val:.3e}"
    base, exp = s.split('e')
    exp = int(exp)
    return f"{base} x 10^{exp}"

df = pd.read_csv('../data/oellm_english/preprocessed/oellm_english.csv')
df['C'] = 6.0 * df['D'] * df['N']
gp_features = resolve_grid_features(df) # default: N, D, lr, gbsz
print(df.shape, gp_features)
C_min, C_max = df.C.min(), df.C.max()
print(f"C_min: {format_scientific(C_min)}, C_max: {format_scientific(C_max)}")

(942, 6) ['N', 'D', 'lr', 'gbsz']
C_min: 1.712 x 10^18, C_max: 3.084 x 10^21


In [ ]:
from core.pipelines.loss_law import _supports_compute_axis

split_axis = 'C'
max_frac = 0.5
form_name = 'L0'

pool_df, held_out_df = split_search_space(
    df, max_frac=max_frac, axis=split_axis
)
train_df = pool_df                        # the loop acquires only from the pool
test_df_known = held_out_df
print(f"Split (axis={split_axis}): pool={len(pool_df)} / held-out={len(held_out_df)}")

combined = pd.concat([train_df, test_df_known])
global_pareto = get_pareto_frontier(combined, x_name='C', y_name="loss")
_pool_pareto = global_pareto.loc[global_pareto.index.isin(train_df.index)]
_held_pareto  = global_pareto.loc[global_pareto.index.isin(test_df_known.index)]

form = PARAMETRIC_FORMS[form_name]
supports_C = _supports_compute_axis(form)  # False for width_depth (no compute marginalization)
print(form, supports_C)

Split (axis=C): pool=905 / held-out=37
ParametricForm(name='L0', func=<function functional_form_L0 at 0x1498bd300>, input_cols=['C'], target='loss', use_pareto=True, initial_grid=<function _l0_initial_grid at 0x12c70d080>, bounds=[(np.float64(-6.907755278982137), np.float64(1.3862943611198906)), (None, None), (-1.0, 0.0)], interpretable=<function _l0_interpretable at 0x12c70d120>, signed_params=frozenset({'L0'}), to_L_vs_C=<function _l0_to_L_vs_C at 0x1498bd8a0>, format_fit=<function _l0_format at 0x1498bd800>) True


In [6]:
## also fit the global model for visualization later
fit_quality = 'dense'
_global_df = pd.concat((pool_df, held_out_df))

print(f"Fitting parametric form on all of the data {_global_df.shape}...")
global_best_params, _ = build_fit(
    _global_df, form_name=form_name, y_name="loss", fit_quality=fit_quality
)
print_fit_results(form, global_best_params)

Fitting parametric form on all of the data (942, 6)...
L(C) = 1.597 + 948.098 * C^(-0.1565)


## Load experiment result

In [7]:
import json
from pathlib import Path

import pandas as pd

run_dir = Path(
    # "/Users/swagatam/Desktop/oellm/surrogate_based_scaling_laws/results/vanilla_bo_whole_range/oellm_english/L0/seed_1234/20260818_114041"
    "/Users/swagatam/Desktop/oellm/surrogate_based_scaling_laws/results/debug/vanilla_bo_slab_1e-5_1.5/oellm_english/L0/seed_1234/20260818_064127"
)
history = pd.read_parquet(run_dir / "history.parquet")
run_meta = json.loads((run_dir / "args.json").read_text())
preds = pd.read_parquet(run_dir / "surrogate_predictions.parquet")

init_points_idx = np.array(list(set(history.iloc[0].acquired_idx.tolist()) - {history.iloc[0].new_idx}))
C_window = run_meta['args']['C_window']
init_compute_factor = run_meta['args']['init_compute_factor']
C_lim = history.iloc[0].C_lim # first C_lim to collect the initial points

In [ ]:
if supports_C:
    C_known = _held_pareto["C"].to_numpy()
    L_known = _held_pareto["loss"].to_numpy()
    C_unknown = C_known.max() * 10.0 ** np.arange(1, 3)   # extrapolation curve beyond the grid
else:
    C_known = C_unknown = np.array([])
    
C_known, L_known, C_unknown

(array([2.05620511e+21, 3.08430766e+21]),
 array([2.03439 , 2.010482]),
 array([3.08430766e+22, 3.08430766e+23]))

In [9]:
## animate the parametric-form evolution over BO iterations
from matplotlib import animation
from IPython.display import HTML

# ---- stable axis limits across all frames (so the view doesn't jump) --------
_all_acq_idx = sorted(set().union(*[set(r.acquired_idx.tolist()) for _, r in history.iterrows()]))
_acq_all_df = train_df.loc[_all_acq_idx]

_x_max = float(held_out_df["C"].max())
if len(C_unknown):
    _x_max = max(_x_max, float(C_unknown.max()))
_xlim = (float(_acq_all_df["C"].min()) * 0.8, _x_max * 1.2)

_loss_vals = [float(_acq_all_df["loss"].min()), float(_acq_all_df["loss"].max())]
if len(L_known):
    _loss_vals += [float(np.min(L_known)), float(np.max(L_known))]
_ylim = (min(_loss_vals) * 0.95, max(_loss_vals) * 1.15)

C_split = float(held_out_df["C"].min())  # pool | held-out boundary


def _draw_forms(ax, t):
    ax.clear()
    row = history.iloc[t]
    obs_df = train_df.loc[row.acquired_idx]

    # all observed points + observed pareto frontier
    ax.scatter(obs_df.C, obs_df.loss, marker="o", color="black", s=5, alpha=0.3, zorder=2)
    _obs_pareto = get_pareto_frontier(obs_df, x_name="C", y_name="loss")
    ax.scatter(_obs_pareto["C"], _obs_pareto["loss"], marker="o", color="black",
               zorder=3, s=25, label="observed pareto")

    # held-out eval points + held-out region
    if len(C_known):
        ax.scatter(C_known, L_known, marker="x", color="#265ddc", zorder=5, s=25)
    ax.axvspan(C_split, float(held_out_df["C"].max()),
               color="#008969", alpha=0.25, lw=0, label="held-out region")

    # fitted curves: solid where observed, dashed where extrapolated
    C_grid = np.geomspace(obs_df["C"].min(), _x_max, 200)
    seen = C_grid <= obs_df["C"].max()

    curves = []
    if row.obs_only_params is not None and np.all(np.isfinite(row.obs_only_params)):
        curves.append((row.obs_only_params, "tab:green", "obs only fit"))
    if row["params"] is not None and np.all(np.isfinite(row["params"])):
        curves.append((row["params"], "red", "obs+fant fit"))
    for params, color, label in curves:
        L_hat = form.to_L_vs_C(C_grid, np.asarray(params))
        ax.plot(C_grid[seen], L_hat[seen], color=color, ls="-", label=label)
        ax.plot(C_grid[~seen], L_hat[~seen], color=color, ls="--")

    L_global_hat = form.to_L_vs_C(C_grid, np.asarray(global_best_params))
    ax.plot(C_grid[seen], L_global_hat[seen], color="tab:purple", ls="-.", label="all data fit")
    ax.plot(C_grid[~seen], L_global_hat[~seen], color="tab:purple", ls="--")

    ax.set_yscale("log")
    ax.set_xscale("log")
    ax.set_xlim(*_xlim)
    ax.set_ylim(*_ylim)
    ax.set_xlabel("C")
    ax.set_ylabel("loss")
    ax.set_title(f"fitting - iter {int(row.iter)}")
    ax.legend(fontsize=8, ncol=1, loc="upper right")
    ax.grid(which="major", ls="--", lw=1, alpha=0.5)


# ---- left panel: acquisition view (new point, prev points, current pareto) ----
def _draw_acq(ax, t):
    ax.clear()
    row = history.iloc[t]
    cur_C_lim = row.C_lim
    new_idx = row.new_idx
    acquired = list(row.acquired_idx)
    prev_idx = [i for i in acquired if i != new_idx]

    # previously acquired points (everything except this iteration's new point)
    prev_df = train_df.loc[prev_idx]
    ax.scatter(prev_df["C"], prev_df[loss_key], marker="o", color="black", s=5, alpha=0.3, zorder=2, label="observed points")

    # current pareto frontier over all points acquired so far
    acquired_df = train_df.loc[acquired]
    cur_pareto = get_pareto_frontier(acquired_df, x_name="C", y_name=loss_key)
    ax.scatter(cur_pareto["C"], cur_pareto[loss_key], marker="o", color="black",
               zorder=4, s=25, label="current pareto")

    # C_window built from the current C_lim
    ax.axvline(cur_C_lim, color="gray", linestyle="--", label="$C_{lim}$")
    ax.axvspan(cur_C_lim * C_window[0], cur_C_lim * C_window[1],
               color="lightgreen", alpha=0.25, lw=0, label="$C_{window}$")

    # newly acquired point for this iteration
    if new_idx is not None and not pd.isna(new_idx):
        new_pt = train_df.loc[new_idx]
        ax.scatter(new_pt["C"], new_pt[loss_key], marker="*", color="blue",
                   s=250, zorder=3, edgecolor="white", linewidth=0.8, label="new point")

    ax.set_xscale("log")
    ax.set_yscale("log")  # shared with the fits panel
    ax.set_xlim(*_xlim)  # same x-range as the fits panel
    ax.set_ylim(*_ylim)
    ax.set_xlabel("C")
    ax.set_ylabel("loss")
    ax.set_title(f"acquisition — iter {int(row.iter)}  |  n={int(row.n_acquired)}")
    ax.legend(loc="upper right", fontsize=7)


# ---- middle panel: fantasized predictions + fantasized pareto ----
def _draw_fant(ax, t):
    ax.clear()
    row = history.iloc[t]
    obs_df = train_df.loc[row.acquired_idx]

    # replace loss of unobserved pool points with the surrogate's fantasized prediction
    preds_iter = preds[preds["iter"] == row.iter]
    fant_df = train_df.copy()
    fant_df.loc[preds_iter["idx"], "loss"] = preds_iter["pred_loss"].to_numpy()

    # observed points (context) + fantasized points
    # ax.scatter(obs_df.C, obs_df.loss, marker="o", color="black", s=5, alpha=0.3, zorder=2,
    #            label="observed points")
    ax.scatter(fant_df.C, fant_df.loss, marker="x", color="red", s=5, alpha=0.6, zorder=3,
               label="fantasized points")

    # fantasized pareto frontier
    _fant_pareto = get_pareto_frontier(fant_df, x_name="C", y_name="loss")
    ax.scatter(_fant_pareto["C"], _fant_pareto["loss"], marker="x", color="red",
               s=25, zorder=4, label="fant pareto")

    # held-out eval points + held-out region (shared context with the fits panel)
    if len(C_known):
        ax.scatter(C_known, L_known, marker="x", color="#265ddc", zorder=5, s=25)
    ax.axvspan(C_split, float(held_out_df["C"].max()),
               color="#008969", alpha=0.25, lw=0, label="held-out region")

    ax.set_xscale("log")
    ax.set_yscale("log")
    ax.set_xlim(*_xlim)
    ax.set_ylim(*_ylim)
    ax.set_xlabel("C")
    ax.set_ylabel("loss")
    ax.set_title(f"fantasization — iter {int(row.iter)}")
    ax.legend(loc="upper right", fontsize=7)


# subsample frames to keep the embedded animation a reasonable size
frame_step = 1 #max(1, len(history) // 150)
frames = list(range(0, len(history), frame_step))

fig, (ax_acq, ax_fant, ax_fit) = plt.subplots(
    1, 3, figsize=(3 * (16 // 3), 9 // 2), sharex=True, sharey=True)


def _update(t):
    _draw_acq(ax_acq, t)
    _draw_fant(ax_fant, t)
    _draw_forms(ax_fit, t)


anim = animation.FuncAnimation(fig, _update, frames=frames, interval=120)
plt.close(fig)  # prevent a duplicate static figure from showing
HTML(anim.to_jshtml())

In [10]:
anim.save("../results/animation/slab_bo_fant_animation.mp4", fps=8, dpi=150)